# Data Validation

This notebook can be run then read to ensure the final data before model training passes certain validation checks.

It only performs these validation checks on fight data after

In [1]:
# Change the working directory so globals can load
import os
os.chdir("E:/Repos/mma_model/")

In [2]:
# Read in the data
exec(open('global.py').read())

# Set the option to display 100 rows
pd.set_option('display.max_rows', None)

final_data = fp.ParquetFile('./data/final_dataset.parquet').to_pandas()

# Filter the data
final_data = final_data[final_data['date'] > config['start_date_validation_checks']]


# Missing data checks

The following checks are on columns that should not have any missing data. If there are any, checks will fail and these need to be investigated.

## Check on all fighters (ignoring historic stats)

In [3]:
# Exclude columns containing these strings because they're expected to have some missing
exclude_strings = ['_round', 'allround', 'date_last', 'hist']

# Get a list of columns where we expect no missing values
columns_no_missing = [col for col in final_data.columns if all(sub not in col for sub in exclude_strings)]

# Get a data frame of the counts of missing values
missing_counts = pd.DataFrame(final_data[columns_no_missing].isna().sum(axis = 0), columns = ['nan_count'])

In [4]:
missing_counts[missing_counts['nan_count'] > 0]

,nan_count
fighter1_fighter_type,922
fighter2_fighter_type,1612
fighter1_open_odds,1202
fighter1_best_closing_odds,1202
fighter1_odds_change,1202
fighter2_open_odds,1211
fighter2_best_closing_odds,1211
fighter2_odds_change,1211
fighter1_weight,12
fighter1_reach,340


## Check on all fighters with at least 1 fight in the data

In [5]:
# Exclude columns containing these strings because they're expected to have some missing
# Only look at fighter 1 first and not all will have made it past round 1. Percents can have 0 denominator
exclude_strings = ['_round2', '_round3', '_round4', '_round5', 'opp_stance', 'percent', 'last_knocked', 'over']

# Get a list of columns where we expect no missing values
columns_no_missing = [col for col in final_data.columns if all(sub not in col for sub in exclude_strings)]

filtered_df = final_data[(final_data['fighter1_hist_fights'] > 0) & (final_data['fighter2_hist_fights'] > 0)]

# Get a data frame of the counts of missing values
missing_counts = pd.DataFrame(filtered_df[columns_no_missing].isna().sum(axis = 0), columns = ['nan_count'])

print(f"{len(filtered_df)} fights chosen")

5733 fights chosen


In [6]:
missing_counts[missing_counts['nan_count'] > 0]

,nan_count
fighter1_fighter_type,57
fighter2_fighter_type,107
fighter1_hist_opp_type_round1_kd,107
fighter1_hist_opp_type_round1_ctrl_minutes,107
fighter1_hist_opp_type_round1_fight_minutes,107
fighter1_hist_opp_type_round1_sub.att,107
fighter1_hist_opp_type_round1_sig.str._landed,107
fighter1_hist_opp_type_round1_sig.str._attempt,107
fighter1_hist_opp_type_round1_total_str._landed,107
fighter1_hist_opp_type_round1_total_str._attempt,107


## Experienced fighters

This missing check doesn't ignore columns and only checks experienced fighters where we'd expect no missing values

In [7]:
# Exclude columns containing these strings because they're expected to have some missing
# Only look at fighter 1 first and not all will have made it past round 1. Percents can have 0 denominator
exclude_strings = ['_round4', '_round5', 'opp_stance']

# Get a list of columns where we expect no missing values
columns_no_missing = [col for col in final_data.columns if all(sub not in col for sub in exclude_strings)]

filtered_df = final_data[(final_data['fighter1_hist_fights'] > 15) & (final_data['fighter2_hist_fights'] > 15)]

# Get a data frame of the counts of missing values
missing_counts = pd.DataFrame(filtered_df[columns_no_missing].isna().sum(axis = 0), columns = ['nan_count'])

print(f"{len(filtered_df)} fights chosen")

211 fights chosen


In [8]:
missing_counts[missing_counts['nan_count'] > 0].sort_values(by = 'nan_count')

,nan_count
diff_ratio_hist_last_3_fights_round3_head_landed,1
fighter2_hist_last_3_fights_round2_clinch_attempt_per_minute,1
fighter2_hist_last_3_fights_round2_ground_landed_per_minute,1
fighter2_hist_last_3_fights_round2_ground_attempt_per_minute,1
fighter2_hist_last_3_fights_round2_kd_against_per_minute,1
fighter2_hist_last_3_fights_round2_ctrl_minutes_against_per_minute,1
fighter2_hist_last_3_fights_round2_sub.att_against_per_minute,1
fighter2_hist_last_3_fights_round2_sig.str._landed_against_per_minute,1
fighter2_hist_last_3_fights_round2_sig.str._attempt_against_per_minute,1
fighter2_hist_last_3_fights_round2_total_str._landed_against_per_minute,1


# Valid amounts check

This section checks columns like percentages are between 0 and 1

In [9]:
# Get percentage columns
percent_columns = [col for col in final_data.columns if ('percent' in col) and not ('diff' in col) and not ('minus' in col)]

mins_df = pd.DataFrame(final_data[percent_columns].min(), columns = ['min'])

mins_df[mins_df['min'] < 0]

,min


In [11]:
# Get percentage columns
maxs_df = pd.DataFrame(final_data[percent_columns].max(), columns = ['max'])

maxs_df[maxs_df['max'] > 1]

final_data[final_data['fighter2_hist_allrounds_ctrl_minutes_against_per_minute'] > 1][['fighter2', 'fighter2_hist_allrounds_ctrl_minutes_against_per_minute', 'fighter2_hist_allrounds_ctrl_minutes_against_per_minute', 'fighter2_hist_allrounds_fight_minutes']]

,fighter2,fighter2_hist_allrounds_ctrl_minutes_against_per_minute,fighter2_hist_allrounds_ctrl_minutes_against_per_minute,fighter2_hist_allrounds_fight_minutes


In [12]:
final_data[(final_data['fighter1'] == 'AntonioSilva') | (final_data['fighter2'] == 'AntonioSilva')]



,level_0,fighter1,fighter2,outcome,method,weightclass,date,time_format,fighter1_start_elo,fighter2_start_elo,fighter1_date_last_fight,fighter2_date_last_fight,fighter1_date_last_knocked_out,fighter1_hist_times_knocked_out,fighter1_hist_times_knocked_out_round_1,fighter1_hist_times_knocked_out_round_2,fighter1_hist_times_knocked_out_round_3,fighter1_hist_times_knocked_out_round_4,fighter1_hist_times_knocked_out_round_5,fighter2_date_last_knocked_out,fighter2_hist_times_knocked_out,fighter2_hist_times_knocked_out_round_1,fighter2_hist_times_knocked_out_round_2,fighter2_hist_times_knocked_out_round_3,fighter2_hist_times_knocked_out_round_4,fighter2_hist_times_knocked_out_round_5,fighter1_hist_round1_kd,fighter1_hist_round1_ctrl_minutes,fighter1_hist_round1_fight_minutes,fighter1_hist_round1_sub.att,fighter1_hist_round1_sig.str._landed,fighter1_hist_round1_sig.str._attempt,fighter1_hist_round1_total_str._landed,fighter1_hist_round1_total_str._attempt,fighter1_hist_round1_td_landed,fighter1_hist_round1_td_attempt,fighter1_hist_round1_head_landed,fighter1_hist_round1_head_attempt,fighter1_hist_round1_body_landed,fighter1_hist_round1_body_attempt,fighter1_hist_round1_leg_landed,fighter1_hist_round1_leg_attempt,fighter1_hist_round1_distance_landed,fighter1_hist_round1_distance_attempt,fighter1_hist_round1_clinch_landed,fighter1_hist_round1_clinch_attempt,fighter1_hist_round1_ground_landed,fighter1_hist_round1_ground_attempt,fighter1_hist_round2_kd,fighter1_hist_round2_ctrl_minutes,fighter1_hist_round2_fight_minutes,fighter1_hist_round2_sub.att,fighter1_hist_round2_sig.str._landed,fighter1_hist_round2_sig.str._attempt,fighter1_hist_round2_total_str._landed,fighter1_hist_round2_total_str._attempt,fighter1_hist_round2_td_landed,fighter1_hist_round2_td_attempt,fighter1_hist_round2_head_landed,fighter1_hist_round2_head_attempt,fighter1_hist_round2_body_landed,fighter1_hist_round2_body_attempt,fighter1_hist_round2_leg_landed,fighter1_hist_round2_leg_attempt,fighter1_hist_round2_distance_landed,fighter1_hist_round2_distance_attempt,fighter1_hist_round2_clinch_landed,fighter1_hist_round2_clinch_attempt,fighter1_hist_round2_ground_landed,fighter1_hist_round2_ground_attempt,fighter1_hist_round3_kd,fighter1_hist_round3_ctrl_minutes,fighter1_hist_round3_fight_minutes,fighter1_hist_round3_sub.att,fighter1_hist_round3_sig.str._landed,fighter1_hist_round3_sig.str._attempt,fighter1_hist_round3_total_str._landed,fighter1_hist_round3_total_str._attempt,fighter1_hist_round3_td_landed,fighter1_hist_round3_td_attempt,fighter1_hist_round3_head_landed,fighter1_hist_round3_head_attempt,fighter1_hist_round3_body_landed,fighter1_hist_round3_body_attempt,fighter1_hist_round3_leg_landed,fighter1_hist_round3_leg_attempt,fighter1_hist_round3_distance_landed,fighter1_hist_round3_distance_attempt,fighter1_hist_round3_clinch_landed,fighter1_hist_round3_clinch_attempt,fighter1_hist_round3_ground_landed,fighter1_hist_round3_ground_attempt,fighter1_hist_round4_kd,fighter1_hist_round4_ctrl_minutes,fighter1_hist_round4_fight_minutes,fighter1_hist_round4_sub.att,fighter1_hist_round4_sig.str._landed,fighter1_hist_round4_sig.str._attempt,fighter1_hist_round4_total_str._landed,fighter1_hist_round4_total_str._attempt,fighter1_hist_round4_td_landed,fighter1_hist_round4_td_attempt,fighter1_hist_round4_head_landed,fighter1_hist_round4_head_attempt,fighter1_hist_round4_body_landed,fighter1_hist_round4_body_attempt,fighter1_hist_round4_leg_landed,fighter1_hist_round4_leg_attempt,fighter1_hist_round4_distance_landed,fighter1_hist_round4_distance_attempt,fighter1_hist_round4_clinch_landed,fighter1_hist_round4_clinch_attempt,fighter1_hist_round4_ground_landed,fighter1_hist_round4_ground_attempt,fighter1_hist_round5_kd,fighter1_hist_round5_ctrl_minutes,fighter1_hist_round5_fight_minutes,fighter1_hist_round5_sub.att,fighter1_hist_round5_sig.str._landed,fighter1_hist_round5_sig.str._attempt,fighter1_hist_round5_total_str._landed,fighter1_hist_round5_total_str._attempt,fighter1_hist_round

In [82]:
# Get a boolean DataFrame where values < 0 or > 1 in the percent_columns are marked as True
condition = (final_data[percent_columns] < 0) | (final_data[percent_columns] > 1)

# Find rows where any of the percent_columns values are outside the [0, 1] range
rows_with_out_of_range_values = condition.any(axis=1)

# Calculate the percentage of rows with one or more values < 0 or > 1
percentage_of_invalid_rows = (rows_with_out_of_range_values.sum() / len(final_data)) * 100

# Print the result
print(f"Percentage of rows with out-of-range percentage values: {percentage_of_invalid_rows:.2f}%")



Percentage of rows with out-of-range values: 0.09%
